### Dataset and Task Metadata

In [1]:
from data_foundry.schema import DatasetMetadata, PredictiveMLTaskMetadata

dataset_mold = DatasetMetadata(
    unique_name="smoking_lung_cancer",
    dataset_year="2006",
    domain_str="medical & healthcare",
    # Data Source
    dataset_source="GOV Website",
    original_dataset_source_download_link="https://www.ncbi.nlm.nih.gov/geo/query/acc.cgi?acc=GSE4115",
    download_description="""
We download the original gene expression data from the GEO records.

mkdir -p local-data-warehouse/smoking_lung_cancer/ && wget -P local-data-warehouse/smoking_lung_cancer/ https://ftp.ncbi.nlm.nih.gov/geo/series/GSE4nnn/GSE4115/matrix/GSE4115_series_matrix.txt.gz && gzip -d local-data-warehouse/smoking_lung_cancer/GSE4115_series_matrix.txt.gz
""",
    # References
    academic_reference_bibtex="""@article{Spira2007AirwayEG,
  title={Airway epithelial gene expression in the diagnostic evaluation of smokers with suspect lung cancer},
  author={Avrum Spira and Jennifer Beane and Vishal Shah and Katrina Steiling and Gang Liu and Frank Schembri and Sara Gilman and Yves-Martine Dumas and Paula Calner and Paola Sebastiani and others},
  journal={Nature Medicine},
  year={2007},
  volume={13},
  number={3},
  pages={361-366},
  doi={10.1038/nm1556},
  url={https://doi.org/10.1038/nm1556}
}
""",
    academic_reference_bibtex_key="Spira2007AirwayEG",
    license="Public Domain",
    data_tags=["IID"],
    curation_comments="""
        - We start with an extended dataset of 192 patients. The original reference uses 129 samples as "Individuals without final diagnoses as of May 2005 were excluded from this primary dataset".
        - We remove 5 samples without a clear label ("suspiction of lung cancer"), yielding a dataset of 187 samples.
        - We use "Sample_title" from the metadata as labels for the prediction task.
""",
)
task_mold = PredictiveMLTaskMetadata(
    target_column_name="DiagnosedCancer",
    problem_type="binary_classification",
    objective_metric_name="roc_auc",
    stratify_on="DiagnosedCancer",
)

## Preprocessing

In [2]:
import pandas as pd

df = pd.read_csv(dataset_mold.path / "GSE4115_series_matrix.txt", sep="\t", comment="!", index_col=0)
df = df.T

# read labels
with open(dataset_mold.path / "GSE4115_series_matrix.txt") as f:
    for line in f:
        if line.startswith("!Sample_title"):
            labels = [t.strip('"') for t in line.strip().split("\t")[1:]]
            break

df["DiagnosedCancer"] = pd.Series(labels, index=df.index)
df["DiagnosedCancer"] = df["DiagnosedCancer"].map(
    lambda x: "Yes" if "diagnosed with cancer" in x and "NOT" not in x
              else "No" if "NOT diagnosed" in x
              else None
).astype("category")

df.dropna(subset=["DiagnosedCancer"], inplace=True) # remove suspected cancer samples
df.reset_index(drop=True, inplace=True)
df.columns.name = None

## Data Checks

In [3]:
from data_foundry import dataset_checks
df_head, summary, numeric_stats, cat_stats, target_df = dataset_checks.run_all_checks(
    data=df,
    classification=task_mold.is_classification,
    target_feature=task_mold.target_column_name,
    print_report=False, # In notebook...
)


#### Dataset Overview
Rows: 187
Columns: 22216
Use sampling: False (sample size: 187)
Get row duplicates (staged, merged)...
Using top-10 columns for initial filtering: ['211707_s_at', '215081_at', '215079_at', '215078_at', '215077_at', '215076_s_at', '215075_s_at', '215074_at', '215073_s_at', '215071_s_at']
Rows remaining as candidates after top-10 filter: 0 (of 187)

#### Duplicate Report
Total duplicate rows: 0 (0.00% of dataset)
Duplicate rows ignoring target: 0 (0.00% of dataset)
Get column duplicates...
Duplicate columns: 0 (0.00% of columns)

Data quality checks completed.


In [4]:
# Sample Rows
df_head

,1007_s_at,1053_at,117_at,121_at,1255_g_at,1294_at,1316_at,1320_at,1405_i_at,1431_at,1438_at,1487_at,1494_f_at,1598_g_at,160020_at,1729_at,1773_at,177_at,179_at,1861_at,200000_s_at,200001_at,200002_at,200003_s_at,200004_at,200005_at,200006_at,200007_at,200008_s_at,200009_at,200010_at,200011_s_at,200012_x_at,200013_at,200014_s_at,200015_s_at,200016_x_at,200017_at,200018_at,200019_s_at,200020_at,200021_at,200022_at,200023_s_at,200024_at,200025_s_at,200026_at,200027_at,200028_s_at,200029_at,200030_s_at,200031_s_at,200032_s_at,200033_at,200034_s_at,200035_at,200036_s_at,200037_s_at,200038_s_at,200039_s_at,200040_at,200041_s_at,200042_at,200043_at,200044_at,200045_at,200046_at,200047_s_at,200048_s_at,200049_at,200050_at,200051_at,200052_s_at,200053_at,200054_at,200055_at,200056_s_at,200057_s_at,200058_s_at,200059_s_at,200060_s_at,200061_s_at,200062_s_at,200063_s_at,200064_at,200065_s_at,200066_at,200067_x_at,200068_s_at,200069_at,200070_at,200071_at,200072_s_at,200073_s_at,200074_s_at,200075_s_at,200076_s_at,200077_s_at,200078_s_at,200079_s_at,200080_s_at,200081_s_at,200082_s_at,200083_at,200084_at,200085_s_at,200086_s_at,200087_s_at,200088_x_at,200089_s_at,200090_at,200091_s_at,200092_s_at,200093_s_at,200094_s_at,200095_x_at,200096_s_at,200097_s_at,200098_s_at,200099_s_at,200593_s_at,200594_x_at,200595_s_at,200596_s_at,200597_at,200598_s_at,200599_s_at,200600_at,200601_at,200602_at,200603_at,200604_s_at,200605_s_at,200606_at,200607_s_at,200608_s_at,200609_s_at,200610_s_at,200611_s_at,200612_s_at,200613_at,200614_at,200615_s_at,200616_s_at,200617_at,200618_at,200619_at,200620_at,200621_at,200622_x_at,200623_s_at,200624_s_at,200625_s_at,200626_s_at,200627_at,200628_s_at,200629_at,200630_x_at,200631_s_at,200632_s_at,200633_at,200634_at,200635_s_at,200636_s_at,200637_s_at,200638_s_at,200639_s_at,200640_at,200641_s_at,200642_at,200643_at,200644_at,200645_at,200646_s_at,200647_x_at,200648_s_at,200649_at,200650_s_at,200651_at,200652_at,200653_s_at,200654_at,200655_s_at,200656_s_at,200657_at,200658_s_at,200659_s_at,200660_at,200661_at,200662_s_at,200663_at,200664_s_at,200665_s_at,200666_s_at,200667_at,200668_s_at,200669_s_at,200670_at,200671_s_at,200672_x_at,200673_at,200674_s_at,200675_at,200676_s_at,200677_at,200678_x_at,200679_x_at,200680_x_at,200681_at,200682_s_at,200683_s_at,200684_s_at,200685_at,200686_s_at,200687_s_at,200688_at,200689_x_at,200690_at,200691_s_at,200692_s_at,200693_at,200694_s_at,200695_at,200696_s_at,200697_at,200698_at,200699_at,200700_s_at,200701_at,200702_s_at,200703_at,200704_at,200705_s_at,200706_s_at,200707_at,200708_at,200709_at,200710_at,200711_s_at,200712_s_at,200713_s_at,200714_x_at,200715_x_at,200716_x_at,200717_x_at,200718_s_at,200719_at,200720_s_at,200721_s_at,200722_s_at,200723_s_at,200724_at,200725_x_at,200726_at,200727_s_at,200728_at,200729_s_at,200730_s_at,200731_s_at,200732_s_at,200733_s_at,200734_s_at,200735_x_at,200736_s_at,200737_at,200738_s_at,200739_s_at,200740_s_at,200741_s_at,200742_s_at,200743_s_at,200744_s_at,200745_s_at,200746_s_at,200747_s_at,200748_s_at,200749_at,200750_s_at,200751_s_at,200752_s_at,200753_x_at,200754_x_at,200755_s_at,200756_x_at,200757_s_at,200758_s_at,200759_x_at,200760_s_at,200761_s_at,200762_at,200763_s_at,200764_s_at,200765_x_at,200766_at,200767_s_at,200768_s_at,200769_s_at,200770_s_at,200771_at,200772_x_at,200773_x_at,200774_at,200775_s_at,200776_s_at,200777_s_at,200778_s_at,200779_at,200780_x_at,200781_s_at,200782_at,200783_s_at,200784_s_at,200785_s_at,200786_at,200787_s_at,200788_s_at,200789_at,200790_at,200791_s_at,200792_at,200793_s_at,200794_x_at,200795_at,200796_s_at,200797_s_at,200798_x_at,200799_at,200800_s_at,200801_x_at,200802_at,200803_s_at,200804_at,200805_at,200806_s_at,200807_s_at,200808_s_at,200809_x_at,200810_s_at,200811_at,200812_at,200813_s_at,200814_at,200815_s_at,200816_s_at,200817_x_at,200818_at,200819_s_at,200820_at,200821_at,200822_x_at,200823_x_at,200824_at,200825_s_at,200826_at,200827_at,200828_s_at,200829_x_at,200830_at,200831_s_at,200832_

In [5]:
# Feature Summary
summary

,index,dtype,n_missing,pct_missing,n_unique,examples
0,DiagnosedCancer,category,0.0,0.0,2.0,"Yes, No"
1,1007_s_at,float64,0.0,0.0,187.0,"10.6969, 10.0359, 10.1716, 9.8467, 10.0514, 10.174, 10.4358, 9.9914, 9.9862, 10.338"
2,1053_at,float64,0.0,0.0,187.0,"4.2362, 4.2379, 4.4506, 4.3611, 4.3881, 4.2188, 4.3957, 4.3787, 4.2991, 4.3833"
3,117_at,float64,0.0,0.0,187.0,"5.3453, 5.3908, 5.4525, 5.797, 5.6742, 5.837, 5.3884, 5.6388, 5.365, 5.4214"
4,121_at,float64,0.0,0.0,187.0,"7.9192, 8.0463, 7.8566, 8.094, 8.0179, 8.1622, 7.7146, 8.0502, 8.324, 7.8113"
5,1255_g_at,float64,0.0,0.0,187.0,"3.4787, 3.7184, 3.7836, 3.8669, 3.8881, 3.7902, 3.6191, 3.7312, 3.9124, 3.5874"
6,1294_at,float64,0.0,0.0,187.0,"7.1425, 7.2224, 7.0207, 7.5555, 7.9364, 7.0882, 7.4775, 7.3222, 6.8206, 7.4446"
7,1316_at,float64,0.0,0.0,187.0,"4.814, 5.1997, 5.1537, 5.1782, 5.1103, 5.2633, 5.0301, 4.9664, 5.4015, 4.9423"
8,1320_at,float64,0.0,0.0,187.0,"4.113, 4.2932, 4.0562, 4.3937, 4.3194, 4.272, 4.0423, 4.1769, 4.4382, 4.035"
9,1405_i_at,float64,0.0,0.0,187.0,"6.9484, 5.9223, 5.0691, 5.8935, 6.2318, 4.9951, 5.8498, 6.6873, 6.4125, 6.6001"


In [6]:
# Numeric Feature Statistics
numeric_stats

,count,mean,std,min,max
1007_s_at,187.0,10.178498,0.425882,7.875062,10.795358
1053_at,187.0,4.395848,0.131180,4.112431,4.929978
117_at,187.0,5.666133,0.252431,5.244170,6.931609
121_at,187.0,8.104832,0.198287,7.586138,8.707625
1255_g_at,187.0,3.725673,0.178511,3.367040,4.591188
1294_at,187.0,7.426571,0.241842,6.709161,8.158052
1316_at,187.0,5.149626,0.229374,4.731988,6.017824
1320_at,187.0,4.252206,0.160989,3.899710,4.710339
1405_i_at,187.0,5.883829,0.789964,4.161416,8.445081
1431_at,187.0,3.383104,0.152249,3.023298,4.058564


In [7]:
# Categorical Feature Statistics
cat_stats

value  count    pct
column          rank                    
DiagnosedCancer 1      Yes     97  51.87
                2       No     90  48.13

In [8]:
# Target Distribution
target_df

,count,pct
DiagnosedCancer,,
Yes,97,51.87
No,90,48.13


## Task Curation

In [9]:
from data_foundry.curation_recommendations import get_recommended_splits_dimensions

n_repeats, n_splits, none_or_test_size = get_recommended_splits_dimensions(
    dataset=df,
    group_on=task_mold.group_on,
    time_on=task_mold.time_on,
)
print(f"Recommended splits: n_repeats={n_repeats}, n_splits={n_splits}, test_size={none_or_test_size}")

Recommended splits: n_repeats=20, n_splits=3, test_size=None


In [10]:
from data_foundry.schema import PredictiveMLSplitsMetadata
from data_foundry import curation_recommendations

splits = curation_recommendations.get_recommended_iid_splits(
    dataset=df,
    n_repeats=n_repeats,
    n_splits=n_splits,
    test_size=none_or_test_size,
    stratify_on=task_mold.stratify_on,
)

splits_mold = PredictiveMLSplitsMetadata(
    splits_comment="Default splits.",
    splits=splits,
)

Using Stratified IID splits.


## Export

In [11]:
from data_foundry.curation_container import CuratedContainer
curated_data = CuratedContainer(
    dataset=df,
    dataset_metadata=dataset_mold,
    task_metadata=task_mold,
    experiment_metadata=splits_mold,
 )
curated_data.save()
print(curated_data.uuid)
print(curated_data.checksum)

Calculating checksum for curated container...
Saving curated container to smoking_lung_cancer/019d9d39-8c7b-7055-bc93-cdfaeb07e398
019d9d39-8c7b-7055-bc93-cdfaeb07e398
e8bcd17563689b6bb1558f9495da7c76cc7b81669c10e90d6baaf7e36fd0b276
